# 🛡️ Sunrise GuardRail: Backtest Institucional com Custos Reais da Corretora
### Ativo: BTCUSD (M15) | Corretora: VT Markets | Conta Demo: 1123867

Este notebook executa o teste formal dos **gatilhos de entrada e saída institucionais**, incorporando **100% dos custos reais e auditados da conta do usuário**:

### 📊 Custos Operacionais Auditados na Corretora:
1. **Spread Médio:** **~$16.96 USD por Bitcoin** (~1.696 pontos) debitado em todas as entradas a mercado.
2. **Swap / Rollover Overnight:**
   * **Compras (Long):** **-20.0% ao ano** debitado proporcionalmente a cada virada de dia (21:00 UTC).
   * **Rollover Triplo:** Cobrança de **3 dias de swap às sextas-feiras**.
   * **Vendas (Short):** **0.0%** (Isento de swap na VT Markets).
3. **Comissão:** **$0.00** (Conta Standard/VIP remunerada via spread).
4. **Margem & Alavancagem:** Alavancagem **1:500** com risco estrito de **1.0% do patrimônio por trade**.

### 🎯 Gatilhos Validados:
* **Entrada:** Volume Clímax ou Rising (PVSRA) + Tendência alinhada à `EMA 200` e `EMA 50` + Vela direcional fechada.
* **Filtro GuardRail:** Sessões de alta liquidez (Londres 08h-12h UTC / NY 15h-19h UTC nos dias úteis) + Trava de Spread Drag (< 5%).
* **Saída:** Stop Loss dinâmico ATR 1.5x e Take Profit Payoff 2:1 (2x a distância do SL).

In [3]:
# 1. Instalação de dependências no Colab (caso executado em nuvem)
!pip install --quiet pyarrow fastparquet plotly

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 2.0/2.0 MB 37.8 MB/s eta 0:00:00


In [4]:
# @title 📦 1. Base de Dados Histórica Embutida (BTCUSD M15 - 88.776 Barras) { display-mode: "form" }
# O DataFrame está 100% embutido diretamente neste arquivo .ipynb em formato comprimido.
# Nenhum upload de arquivo é necessário! Basta executar esta célula.

import base64
import io
import pandas as pd
import numpy as np
import plotly.graph_objects as go
from plotly.subplots import make_subplots

print("[+] Decodificando DataFrame embutido no próprio notebook...")
_EMBEDDED_DATA = """..."""

df = pd.read_parquet(io.BytesIO(base64.b64decode(_EMBEDDED_DATA)))
df["datetime"] = pd.to_datetime(df["datetime"])
df.sort_values("datetime", inplace=True)
df.reset_index(drop=True, inplace=True)

print(f"[SUCESSO] DataFrame carregado: {len(df):,} barras!")
print(f"[PERÍODO] {df['datetime'].min()} até {df['datetime'].max()} (UTC)")
try:
    display(df.head())
except NameError:
    print(df.head())


[+] Decodificando DataFrame embutido no próprio notebook...
[SUCESSO] DataFrame carregado: 88,776 barras!
[PERÍODO] 2024-02-20 22:45:00+00:00 até 2026-09-30 04:15:00+00:00 (UTC)


,datetime,open,high,low,close,tick_volume,spread
0,2024-02-20 22:45:00+00:00,52056.33,52082.99,52019.00,52019.00,139,1001
1,2024-02-20 23:00:00+00:00,52019.00,52153.95,52001.00,52152.87,293,1001
2,2024-02-20 23:15:00+00:00,52152.87,52191.72,52104.47,52148.86,150,1001
3,2024-02-20 23:30:00+00:00,52148.86,52252.71,52118.97,52252.71,181,1001
4,2024-02-20 23:45:00+00:00,52252.71,52299.75,52163.65,52163.65,188,1001


### 3. Engenharia de Features e Indicadores Institucionais (PVSRA + Médias + ATR)

In [5]:
# Médias Móveis Exponenciais de Tendência
df['ema_50'] = df['close'].ewm(span=50, adjust=False).mean()
df['ema_200'] = df['close'].ewm(span=200, adjust=False).mean()

# ATR (True Range com janela de 14 períodos)
prev_close = df['close'].shift(1)
tr1 = df['high'] - df['low']
tr2 = (df['high'] - prev_close).abs()
tr3 = (df['low'] - prev_close).abs()
df['tr'] = pd.concat([tr1, tr2, tr3], axis=1).max(axis=1)
df['atr'] = df['tr'].rolling(14).mean()

# PVSRA (Price Volume Spread Analysis)
lookback_pvsra = 10
df['avg_vol'] = df['tick_volume'].rolling(lookback_pvsra).mean()
df['candle_spread'] = (df['close'] - df['open']).abs()
df['avg_spread'] = df['candle_spread'].rolling(lookback_pvsra).mean()

cond_climax = (df['tick_volume'] >= 2.0 * df['avg_vol']) | ((df['tick_volume'] * df['candle_spread']) >= (2.0 * df['avg_vol'] * df['avg_spread']))
cond_rising = (df['tick_volume'] >= 1.5 * df['avg_vol'])

df['pvsra'] = 0
df.loc[cond_rising, 'pvsra'] = 1   # Rising Volume
df.loc[cond_climax, 'pvsra'] = 2   # Climax Volume

# Horários UTC para filtro de sessão
df['hour_utc'] = df['datetime'].dt.hour
df['day_of_week'] = df['datetime'].dt.dayofweek

print("Distribuição PVSRA:")
pvsra_names = {0: 'NORMAL', 1: 'RISING', 2: 'CLIMAX'}
print(df['pvsra'].map(pvsra_names).value_counts())

Distribuição PVSRA:
pvsra
NORMAL    74064
CLIMAX    12945
RISING     1767
Name: count, dtype: int64


### 4. Motor Barra-a-Barra com Custos Reais de Spread e Swap Overnight

In [6]:
def run_institutional_backtest_with_costs(
    df_data,
    rr_ratio=2.0,
    atr_mult_sl=1.5,
    risk_percent=1.0,
    initial_capital=10000.0,
    max_spread_drag_pct=5.0,
    swap_long_annual_rate=0.20,  # 20% ao ano para compras na VT Markets
    use_session_filter=True
):
    """
    Simulador realista com todos os custos auditados da VT Markets:
    - Spread real debitado na abertura da ordem.
    - Swap overnight debitado diariamente para posições de compra.
    - Rollover triplo na sexta-feira.
    - Risco estrito de 1% com juros compostos.
    """
    n = len(df_data)
    opens = df_data['open'].values
    highs = df_data['high'].values
    lows = df_data['low'].values
    closes = df_data['close'].values
    spreads = df_data['spread'].values * 0.01  # Spread da corretora em USD
    atrs = df_data['atr'].values
    pvsras = df_data['pvsra'].values
    ema_50s = df_data['ema_50'].values
    ema_200s = df_data['ema_200'].values
    dates = pd.to_datetime(df_data['datetime'].values)
    hours = df_data['hour_utc'].values
    dows = df_data['day_of_week'].values

    trades = []
    in_position = False
    pos_type = 0  # 1 = Compra, -1 = Venda
    entry_price = 0.0
    sl_price = 0.0
    tp_price = 0.0
    entry_idx = 0
    lot_size = 0.0
    balance = initial_capital
    equity_curve = [initial_capital]
    equity_dates = [dates[0]]

    total_spread_cost = 0.0
    total_swap_cost = 0.0
    rejections = {'session': 0, 'spread_drag': 0}

    for i in range(200, n - 1):
        # 1. GERENCIAMENTO DE POSIÇÃO ATIVA
        if in_position:
            h, l = highs[i], lows[i]
            exit_trade = False
            exit_price = 0.0
            outcome = ""

            if pos_type == 1:  # Compra
                if l <= sl_price:
                    exit_price = sl_price
                    outcome = "SL"
                    exit_trade = True
                elif h >= tp_price:
                    exit_price = tp_price
                    outcome = "TP"
                    exit_trade = True
            elif pos_type == -1:  # Venda
                if h >= sl_price:
                    exit_price = sl_price
                    outcome = "SL"
                    exit_trade = True
                elif l <= tp_price:
                    exit_price = tp_price
                    outcome = "TP"
                    exit_trade = True

            if exit_trade:
                # PnL Bruto de Mercado
                if pos_type == 1:
                    gross_pnl = (exit_price - entry_price) * lot_size
                else:
                    gross_pnl = (entry_price - exit_price) * lot_size

                # CÁLCULO DE SWAP OVERNIGHT (VT Markets: 21:00 UTC)
                trade_swap = 0.0
                if pos_type == 1:  # Apenas compra paga swap no BTCUSD da VT Markets
                    e_date = dates[entry_idx]
                    x_date = dates[i]
                    rollover_points = pd.date_range(e_date.floor('D') + pd.Timedelta(hours=21), x_date, freq='1D')
                    for r in rollover_points:
                        if e_date < r <= x_date:
                            # Sexta-feira às 21h UTC cobra 3 dias de swap (fim de semana)
                            days = 3 if r.dayofweek == 4 else 1
                            trade_swap += (lot_size * entry_price * (swap_long_annual_rate / 360.0)) * days

                total_swap_cost += trade_swap
                net_pnl = gross_pnl - trade_swap
                balance += net_pnl

                trades.append({
                    'entry_date': dates[entry_idx],
                    'exit_date': dates[i],
                    'type': 'BUY' if pos_type == 1 else 'SELL',
                    'lot_size': lot_size,
                    'entry_price': entry_price,
                    'exit_price': exit_price,
                    'sl': sl_price,
                    'tp': tp_price,
                    'outcome': outcome,
                    'gross_pnl': gross_pnl,
                    'swap_cost': trade_swap,
                    'net_pnl': net_pnl,
                    'balance': balance,
                    'duration_bars': i - entry_idx,
                    'hour': hours[entry_idx],
                    'dow': dows[entry_idx]
                })

                in_position = False
                pos_type = 0

        equity_curve.append(balance)
        equity_dates.append(dates[i])

        # 2. AVALIAÇÃO DE NOVO SINAL (Apenas se desposicionado)
        if not in_position and not np.isnan(atrs[i]) and atrs[i] > 0:
            if use_session_filter:
                is_london = (8 <= hours[i] < 12)
                is_ny = (15 <= hours[i] < 19)
                is_weekday = (dows[i] < 5)
                if not ((is_london or is_ny) and is_weekday):
                    rejections['session'] += 1
                    continue

            c, o = closes[i], opens[i]
            pvsra = pvsras[i]
            vol_confirmed = (pvsra in [1, 2])
            trend_bull = (c > ema_200s[i]) and (ema_50s[i] > ema_200s[i])
            trend_bear = (c < ema_200s[i]) and (ema_50s[i] < ema_200s[i])

            buy_sig = trend_bull and vol_confirmed and (c > o)
            sell_sig = trend_bear and vol_confirmed and (c < o)

            if buy_sig or sell_sig:
                next_open = opens[i + 1]
                spread = spreads[i + 1]
                atr = atrs[i]

                sl_dist = atr * atr_mult_sl
                tp_dist = sl_dist * rr_ratio
                if sl_dist <= 0 or tp_dist <= 0: continue

                # Trava GuardRail: Spread Drag
                spread_drag = (spread / tp_dist) * 100.0
                if max_spread_drag_pct is not None and spread_drag > max_spread_drag_pct:
                    rejections['spread_drag'] += 1
                    continue

                # Dimensionamento de Lote (Risco estrito de 1%)
                risk_money = balance * (risk_percent / 100.0)
                raw_lot = risk_money / sl_dist
                lot_size = max(0.01, min(100.0, np.floor(raw_lot / 0.01) * 0.01))

                total_spread_cost += (spread * lot_size)
                pos_type = 1 if buy_sig else -1
                entry_idx = i + 1

                if pos_type == 1:
                    entry_price = next_open + spread  # Paga spread na compra
                    sl_price = entry_price - sl_dist
                    tp_price = entry_price + tp_dist
                else:
                    entry_price = next_open
                    sl_price = entry_price + sl_dist + spread
                    tp_price = entry_price - tp_dist

                in_position = True

    df_trades = pd.DataFrame(trades)
    df_equity = pd.DataFrame({'datetime': equity_dates, 'equity': equity_curve})
    costs = {'spread': total_spread_cost, 'swap': total_swap_cost}
    return df_trades, df_equity, costs, rejections

### 5. Relatório Consolidado de Performance com Auditoria de Custos

In [7]:
trades_df, equity_df, broker_costs, rejections = run_institutional_backtest_with_costs(
    df,
    rr_ratio=2.0,
    atr_mult_sl=1.5,
    risk_percent=1.0,
    initial_capital=10000.0,
    max_spread_drag_pct=5.0,
    swap_long_annual_rate=0.20,
    use_session_filter=True
)

total_trades = len(trades_df)
wins = trades_df[trades_df['net_pnl'] > 0]
losses = trades_df[trades_df['net_pnl'] <= 0]
win_rate = (len(wins) / total_trades) * 100.0

final_balance = equity_df['equity'].iloc[-1]
net_profit = final_balance - 10000.0
total_return_pct = (net_profit / 10000.0) * 100.0

gross_profit = trades_df[trades_df['gross_pnl'] > 0]['gross_pnl'].sum()
gross_loss = abs(trades_df[trades_df['gross_pnl'] <= 0]['gross_pnl'].sum())
profit_factor = gross_profit / gross_loss if gross_loss > 0 else np.nan

equity_df['peak'] = equity_df['equity'].cummax()
equity_df['drawdown'] = (equity_df['equity'] - equity_df['peak']) / equity_df['peak'] * 100.0
max_dd = abs(equity_df['drawdown'].min())

print("="*70)
print(f"{'AUDITORIA INTEGRAL COM CUSTOS REAIS (VT MARKETS BTCUSD)':^70}")
print("="*70)
print(f"Total de Operações Executadas:       {total_trades:,}")
print(f"Taxa de Acerto Líquida (Payoff 2:1): {win_rate:.2f}%")
print(f"Profit Factor Líquido:               {profit_factor:.2f}")
print(f"Retorno Líquido Final:               {total_return_pct:+.2f}%")
print(f"Capital Inicial:                     $10,000.00")
print(f"Capital Final (Saldo Líquido):       ${final_balance:,.2f}")
print(f"Drawdown Máximo:                     {max_dd:.2f}%")
print("-"*70)
print(f"{'DEMONSTRATIVO DE CUSTOS PAGOS À CORRETORA':^70}")
print("-"*70)
print(f"Custo Total com Spread Debitados:    ${broker_costs['spread']:,.2f}")
print(f"Custo Total com Swap Overnight:      ${broker_costs['swap']:,.2f}")
print(f"Comissões Pagas:                     $0.00 (Zero)")
print(f"Total Geral de Custos de Fricção:    ${broker_costs['spread'] + broker_costs['swap']:,.2f}")
print("="*70)
print(f"[GuardRail] Ordens Bloqueadas por Fora de Sessão:  {rejections['session']:,}")
print(f"[GuardRail] Ordens Bloqueadas por Spread Drag:     {rejections['spread_drag']:,}")
print("="*70)

       AUDITORIA INTEGRAL COM CUSTOS REAIS (VT MARKETS BTCUSD)        
Total de Operações Executadas:       1,626
Taxa de Acerto Líquida (Payoff 2:1): 37.76%
Profit Factor Líquido:               1.20
Retorno Líquido Final:               +437.63%
Capital Inicial:                     $10,000.00
Capital Final (Saldo Líquido):       $53,762.94
Drawdown Máximo:                     31.41%
----------------------------------------------------------------------
              DEMONSTRATIVO DE CUSTOS PAGOS À CORRETORA               
----------------------------------------------------------------------
Custo Total com Spread Debitados:    $17,263.92
Custo Total com Swap Overnight:      $1,943.18
Comissões Pagas:                     $0.00 (Zero)
Total Geral de Custos de Fricção:    $19,207.10
[GuardRail] Ordens Bloqueadas por Fora de Sessão:  60,164
[GuardRail] Ordens Bloqueadas por Spread Drag:     52


### 6. Gráficos Interativos: Curva de Capital Líquida e Drawdown

In [8]:
fig = make_subplots(
    rows=2, cols=1, shared_xaxes=True, vertical_spacing=0.08, row_heights=[0.7, 0.3],
    subplot_titles=('Evolução do Patrimônio Líquido com Custos Reais Debitados', 'Drawdown Subaquático (%)')
)

fig.add_trace(
    go.Scatter(x=equity_df['datetime'], y=equity_df['equity'], line=dict(color='#00E676', width=2), name='Saldo Líquido ($)'),
    row=1, col=1
)

fig.add_trace(
    go.Scatter(x=equity_df['datetime'], y=[10000.0]*len(equity_df), line=dict(color='#888888', dash='dot'), name='Capital Inicial ($10k)'),
    row=1, col=1
)

fig.add_trace(
    go.Scatter(x=equity_df['datetime'], y=equity_df['drawdown'], fill='tozeroy', line=dict(color='#FF5252', width=1), name='Drawdown (%)'),
    row=2, col=1
)

fig.update_layout(
    height=650,
    title='BTCUSD M15 - Backtest Sunrise GuardRail com Spread e Swap Auditados (VT Markets)',
    hovermode='x unified',
    template='plotly_dark'
)
fig.show()